<a href="https://colab.research.google.com/github/DJ-Ortega/powerlifting-linearRegression/blob/main/LinearRegression_Powerlifting.ipynb" target="_parent"><img src="https://colab.research.google.com/assets/colab-badge.svg" alt="Open In Colab"/></a>

# Predicting powerlifting totals with linear regression.
## Data: OpenPowerlifting (Kaggle).
### Target: TotalKg, from age, bodyweight, sex and equipment.

In [33]:
import kagglehub

path = kagglehub.dataset_download("open-powerlifting/powerlifting-database")

print("Path to dataset files:", path)

Using Colab cache for faster access to the 'powerlifting-database' dataset.
Path to dataset files: /kaggle/input/powerlifting-database


In [34]:
import os
print(os.listdir(path))

['openpowerlifting-2024-01-06-4c732975.csv', 'openpowerlifting.csv']


In [35]:
import pandas as pd
#importing the data into a pandas dataframe
powerlifting_df = pd.read_csv(path + '/openpowerlifting.csv')

/tmp/ipykernel_6795/2571184317.py:3: DtypeWarning:

Columns (35) have mixed types. Specify dtype option on import or set low_memory=False.



In [36]:
powerlifting_df

,Name,Sex,Event,Equipment,Age,AgeClass,Division,BodyweightKg,WeightClassKg,Squat1Kg,...,McCulloch,Glossbrenner,IPFPoints,Tested,Country,Federation,Date,MeetCountry,MeetState,MeetName
0,Abbie Murphy,F,SBD,Wraps,29.0,24-34,F-OR,59.8,60,80.0,...,324.16,286.42,511.15,NaN,NaN,GPC-AUS,2018-10-27,Australia,VIC,Melbourne Cup
1,Abbie Tuong,F,SBD,Wraps,29.0,24-34,F-OR,58.5,60,100.0,...,378.07,334.16,595.65,NaN,NaN,GPC-AUS,2018-10-27,Australia,VIC,Melbourne Cup
2,Ainslee Hooper,F,B,Raw,40.0,40-44,F-OR,55.4,56,NaN,...,38.56,34.12,313.97,NaN,NaN,GPC-AUS,2018-10-27,Australia,VIC,Melbourne Cup
3,Amy Moldenhauer,F,SBD,Wraps,23.0,20-23,F-OR,60.0,60,-105.0,...,345.61,305.37,547.04,NaN,NaN,GPC-AUS,2018-10-27,Australia,VIC,Melbourne Cup
4,Andrea Rowan,F,SBD,Wraps,45.0,45-49,F-OR,104.0,110,120.0,...,338.91,274.56,550.08,NaN,NaN,GPC-AUS,2018-10-27,Australia,VIC,Melbourne Cup
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
1423349,Marian Cafalik,M,SBD,Raw,60.5,60-64,Masters 2,73.5,74,160.0,...,438.27,316.52,469.67,Yes,NaN,PZKFiTS,2017-04-01,Poland,NaN,Polish Classic Powerlifting Cup
1423350,Marian Piwowarczyk,M,SBD,Raw,55.5,55-59,Masters 2,63.5,66,90.0,...,372.60,295.66,423.03,Yes,Poland,PZKFiTS,2017-04-01,Poland,NaN,Polish Classic Powerlifting Cup
1423351,Andrzej Bryniarski,M,SBD,Raw,62.5,60-64,Masters 2,94.4,105,140.0,...,382.36,264.22,378.84,Yes,NaN,PZKFiTS,2017-04-01,Poland,NaN,Polish Classic Powerlifting Cup
1423352,Stanisław Goroczko,M,SBD,Raw,63.5,60-64,Masters 2,80.8,83,-165.0,...,NaN,NaN,NaN,Yes,NaN,PZKFiTS,2017-04-01,Poland,NaN,Polish Classic Powerlifting Cup


In [37]:
print(list(powerlifting_df.columns))

['Name', 'Sex', 'Event', 'Equipment', 'Age', 'AgeClass', 'Division', 'BodyweightKg', 'WeightClassKg', 'Squat1Kg', 'Squat2Kg', 'Squat3Kg', 'Squat4Kg', 'Best3SquatKg', 'Bench1Kg', 'Bench2Kg', 'Bench3Kg', 'Bench4Kg', 'Best3BenchKg', 'Deadlift1Kg', 'Deadlift2Kg', 'Deadlift3Kg', 'Deadlift4Kg', 'Best3DeadliftKg', 'TotalKg', 'Place', 'Wilks', 'McCulloch', 'Glossbrenner', 'IPFPoints', 'Tested', 'Country', 'Federation', 'Date', 'MeetCountry', 'MeetState', 'MeetName']


We want to only predict the total lifts (in Kg's) by a person that has done all three lifts; squat, bench, deadlifts.

We also just want to keep some of the variables (Sex, Age, BodyweightKg, Equipment, TotalKg), not all of them, mainly for simplicity and comprehension.

In [38]:
sbd_df = powerlifting_df[powerlifting_df.Event == 'SBD']

In [39]:
lifters_df = sbd_df[['Sex', 'Age', 'BodyweightKg', 'Equipment', 'TotalKg']]

# Exploratory analysis & Visualization

In [40]:
lifters_df.isna().sum()

,0
Sex,0
Age,573802
BodyweightKg,12389
Equipment,0
TotalKg,88908


In [41]:
#dropping the na's
lifters_df = lifters_df.dropna()
print(lifters_df.shape)

(468421, 5)


In [42]:
lifters_df.describe()

,Age,BodyweightKg,TotalKg
count,468421.000000,468421.000000,468421.000000
mean,29.410169,83.954262,510.760920
std,12.288043,22.615913,180.025208
min,0.000000,17.690000,38.600000
25%,20.500000,66.900000,362.900000
50%,26.000000,81.700000,510.000000
75%,36.000000,98.300000,635.000000
max,95.500000,242.400000,1367.500000


Minimum age = 0??!! That isn't possible, lets take a look.

In [43]:
(lifters_df.Age < 10).sum()

np.int64(385)

In [44]:
(lifters_df.Age < 18).sum()

np.int64(65674)

In [45]:
#let's keep only the adults (18+)
lifters_df = lifters_df[lifters_df.Age >= 18].copy()

In [46]:
lifters_df.shape

(402747, 5)

In [47]:
lifters_df.describe()

,Age,BodyweightKg,TotalKg
count,402747.000000,402747.000000,402747.000000
mean,31.596211,85.540830,529.341408
std,11.879396,22.424088,179.581481
min,18.000000,24.950000,40.800000
25%,22.500000,68.800000,385.000000
50%,28.000000,82.400000,530.700000
75%,38.500000,99.300000,652.500000
max,95.500000,242.400000,1367.500000


Much better!!! Let's now look at the categorical variables.

In [48]:
print(lifters_df.Sex.value_counts())
print(lifters_df.Equipment.value_counts())

Sex
M    287841
F    114906
Name: count, dtype: int64
Equipment
Raw           188483
Single-ply    128652
Wraps          68545
Multi-ply      17067
Name: count, dtype: int64


**Raw:**	No supportive gear. Usually just a belt and knee sleeves (soft neoprene tubes that keep the knees warm but don’t add much).

**Wraps:**	Like raw, but with knee wraps: long elastic bands wound very tightly around the knees. They mainly help the squat: you bend down, they stretch, and they spring you back up.

**Single-ply:**	A supportive suit (for squat and deadlift) and a bench shirt, made of one layer of very stiff, tight material. Much more help than wraps.

**Multi-ply:**	The same idea with several layers. The most support of all, and the biggest totals.

In [49]:
#binary encoding for the sex variable
sex_codes = {'M': 0, 'F': 1}
lifters_df['sex_codes'] = lifters_df.Sex.map(sex_codes)
lifters_df.head()

,Sex,Age,BodyweightKg,Equipment,TotalKg,sex_codes
0,F,29.0,59.8,Wraps,290.0,1
1,F,29.0,58.5,Wraps,332.5,1
3,F,23.0,60.0,Wraps,310.0,1
4,F,45.0,104.0,Wraps,390.0,1
5,F,37.0,74.0,Wraps,370.0,1


In [50]:
#one-hot encoding for the Equipment variable
lifters_encoded = pd.get_dummies(lifters_df, columns=['Equipment'], dtype = int)
lifters_encoded.head()

,Sex,Age,BodyweightKg,TotalKg,sex_codes,Equipment_Multi-ply,Equipment_Raw,Equipment_Single-ply,Equipment_Wraps
0,F,29.0,59.8,290.0,1,0,0,0,1
1,F,29.0,58.5,332.5,1,0,0,0,1
3,F,23.0,60.0,310.0,1,0,0,0,1
4,F,45.0,104.0,390.0,1,0,0,0,1
5,F,37.0,74.0,370.0,1,0,0,0,1


Let's do some visualization

In [51]:
import plotly.express as px
#Distribution of Total Lifted by gender
fig = px.histogram(lifters_df,
                   x = 'TotalKg',
                   color='Sex',
                   marginal='box',
                   title = 'Distribution of Total Lifted (in Kg)')
fig.update_layout(barmode='overlay')
fig.show()

In [52]:
#Bodyweight vs Total
sample_df = lifters_df.sample(5000, random_state=42)
fig = px.scatter(sample_df,
                 x='BodyweightKg',
                 y='TotalKg',
                 color='Sex',
                 opacity=0.5,
                 title='Bodyweight vs. Total')
fig.show()

In [53]:
#TotalKg lifted vs Type of Equipment used
fig = px.box(lifters_df,
            x='Equipment',
            y='TotalKg',
            color='Sex',
            title='TotalKg lifted vs. Type of Equipment used')
fig.show()

## Let's now split the data into a train and a test set

In [54]:
from sklearn.model_selection import train_test_split

In [55]:
input_cols = ['Age', 'BodyweightKg', 'sex_codes', 'Equipment_Raw', 'Equipment_Wraps', 'Equipment_Single-ply', 'Equipment_Multi-ply']
inputs = lifters_encoded[input_cols]
targets = lifters_encoded['TotalKg']
inputs_train, inputs_test, targets_train, targets_test = train_test_split(inputs, targets, test_size=0.2, random_state=42)

## Let's now fit the model on the training set

Root mean squared error:

<img src="https://i.imgur.com/WCanPkA.png" width="360">

In [56]:
#making the RMSE function
import numpy as np
def rmse(targets, predictions):
    return np.sqrt(np.mean(np.square(targets - predictions)))

In [57]:
#fitting the model on the training set
from sklearn.linear_model import LinearRegression
model = LinearRegression().fit(inputs_train, targets_train)
predictions = model.predict(inputs_train)

cost = rmse(targets_train, predictions)
print('Cost: ', cost)

Cost:  99.17529670377002


In [58]:
# evaluating the model on the test set
predictions_test = model.predict(inputs_test)
cost_test = rmse(targets_test, predictions_test)
print('Test cost:', cost_test)

Test cost: 99.13196227678739


We can see that we're on average about 99 kg off from the real total kilograms lifted.


What’s a bit unrealistic:

The model says strength drops steadily with age, from 18 onwards. In reality, most lifters get stronger through their twenties, peak around 30, then decline. A straight line can’t go up and then down, so it averages it all into one gentle slope downwards. The same goes for bodyweight: your scatter plot showed the curve flattening for very heavy lifters, but the model says every extra kg adds the same 3.5 kg, however heavy you already are. Those are the model’s two weak spots, and the natural place to improve it next.

In [60]:
print(model.coef_)
print(model.intercept_)

[  -2.00846426    3.51424789 -176.97111043  -70.32754589  -40.6982619
   22.53842826   88.48737954]
371.4302814029843
